In [ ]:
import gurobipy as gp
from gurobipy import GRB
import os

def load_model(prob):
    gmodel = gp.read(prob)
    gmodel.Params.OutputFlag = 0
    return gmodel

def mod_model(gmodel, decision, vec=None, relax=False):
    if relax:
        gmodel = gmodel.relax()
    var_list = gmodel.getVars()
    N = len(var_list)
    if vec is not None:
        if len(vec) != 2 * N:
            raise ValueError(f"vec must have length 2*N={2*N}, got {len(vec)}")
        for i, var in enumerate(var_list):
            var.LB = vec[i]
            var.UB = vec[i + N]

    if decision[1] == 'L':
        var_list[decision[0]].LB = 0
        var_list[decision[0]].UB = 0
    elif decision[1] == 'R':
        var_list[decision[0]].LB = 1
        var_list[decision[0]].UB = 1
    gmodel.update()
    return gmodel

# ── Globals ────────────────────────────────────────────────────────────────────

result = {}

# ── Callback ───────────────────────────────────────────────────────────────────

def callback(model, where):          # model is passed directly by Gurobi
    global result
    if where == GRB.Callback.BRANCHING:
        idx       = int(model.cbGet(GRB.Callback.BRANCHING_VARINDEX))   # ← model, not current_model
        val       = model.cbGet(GRB.Callback.BRANCHING_VALUE)
        direction = int(model.cbGet(GRB.Callback.BRANCHING_DIRECTION))

        result["var_name"]         = model.getVars()[idx].VarName
        result["var_index"]        = idx
        result["fractional_value"] = val
        result["direction"]        = "down (<= floor)" if direction == -1 else "up (>= ceil)"

        model.terminate()

# ── Runner ─────────────────────────────────────────────────────────────────────

def get_first_branch_var(m, var_branch=1):
    global result

    result = {}  # reset for each model

    m.Params.OutputFlag = 0
    m.Params.VarBranch  = var_branch

    m.optimize(callback)

    return result

# ── Main ───────────────────────────────────────────────────────────────────────

prob      = r"C:\Users\KISHAN\Downloads\2club200v15p5scn.mps\2club200v15p5scn.mps"
filename  = os.path.basename(prob)
name_only = os.path.splitext(filename)[0]

model  = load_model(prob)
models = {
    "m1": mod_model(model.copy(), decision=(0, 'L')),
    "m2": mod_model(model.copy(), decision=(0, 'R')),
    "m3": mod_model(model.copy(), decision=(1, 'L')),
    "m4": mod_model(model.copy(), decision=(1, 'R')),
}

VAR_BRANCH = 1

print(f"Brancher: VarBranch = {VAR_BRANCH}\n")
print(f"{'Model':<28} {'1st Branch Var':<18} {'Frac. Value':<15} {'Direction'}")
print("-" * 80)

first_branch_vars = {}
for name, m in models.items():
    res = get_first_branch_var(m, var_branch=VAR_BRANCH)
    first_branch_vars[name] = res
    if res:
        print(f"{name:<28} {res['var_name']:<18} {res['fractional_value']:<15.4f} {res['direction']}")
    else:
        print(f"{name:<28} No branching occurred (model may be trivially solvable)")

In [ ]:
import gurobipy as gp
from gurobipy import GRB
import os

def load_model(prob):
    gmodel = gp.read(prob)
    gmodel.Params.OutputFlag = 0          # ✅ reads .mps natively, no conversion needed
    return gmodel

# ─────────────────────────────────────────
# (Modifying the BIP model by adding the bounds of the variables from vec so that we get the solution corresponding to each of the states)
# ─────────────────────────────────────────
def mod_model(gmodel, decision, vec=None, relax=False):
    # Relaxation
    if relax:
        gmodel = gmodel.relax()
    # Apply bounds if provided
    var_list = gmodel.getVars()
    N = len(var_list)
    if vec is not None:
        if len(vec) != 2 * N:
            raise ValueError(f"vec must have length 2*N={2*N}, got {len(vec)}")
        for i, var in enumerate(var_list):
            var.LB = vec[i]          # lower bound
            var.UB = vec[i + N]      # upper bound
                       # ✅ must call update() after changing bounds
    
    if decision[1] == 'L':
        var_list[decision[0]].LB = 0
        var_list[decision[0]].UB = 0
    elif decision[1] == 'R':
        var_list[decision[0]].LB = 1
        var_list[decision[0]].UB = 1
    gmodel.update()
    return gmodel



current_model = None
result        = {}

# ── Callback ───────────────────────────────────────────────────────────────────

def callback(model,where):
    global result
    if where == GRB.Callback.BRANCHING:
        idx       = int(current_model.cbGet(GRB.Callback.BRANCHING_VARINDEX))
        val       = current_model.cbGet(GRB.Callback.BRANCHING_VALUE)
        direction = int(current_model.cbGet(GRB.Callback.BRANCHING_DIRECTION))

        result["var_name"]         = current_model.getVars()[idx].VarName
        result["var_index"]        = idx
        result["fractional_value"] = val
        result["direction"]        = "down (<= floor)" if direction == -1 else "up (>= ceil)"

        model.terminate()  # Stop immediately after first branch


# ── Runner ─────────────────────────────────────────────────────────────────────

def get_first_branch_var(m, var_branch=1):
    global current_model, result

    current_model = m    # expose to callback under an unambiguous name
    result        = {}   # reset for each model

    current_model.Params.OutputFlag = 0
    current_model.Params.VarBranch  = var_branch

    current_model.optimize(callback)

    return result


# ── Models ─────────────────────────────────────────────────────────────────────


# ── Main ───────────────────────────────────────────────────────────────────────
prob = r"C:\Users\KISHAN\Downloads\2club200v15p5scn.mps\2club200v15p5scn.mps"
#prob = r"C:\Users\KISHAN\Downloads\stein9inf.mps\stein9inf.mps"
filename  = os.path.basename(prob)         # "2club200v15p5scn.mps"
name_only = os.path.splitext(filename)[0]  # "2club200v15p5scn"
model = load_model(prob)
models = {"m1": mod_model(model.copy(), decision=(0, 'L')),
          "m2": mod_model(model.copy(), decision=(0, 'R')),
          "m3": mod_model(model.copy(), decision=(1, 'L')),
          "m4": mod_model(model.copy(), decision=(1, 'R'))
}

VAR_BRANCH = 1  # Max infeasibility brancher — change to test others

print(f"Brancher: VarBranch = {VAR_BRANCH}\n")
print(f"{'Model':<28} {'1st Branch Var':<18} {'Frac. Value':<15} {'Direction'}")
print("-" * 80)

first_branch_vars = {}
for name, m in models.items():
    res = get_first_branch_var(m, var_branch=VAR_BRANCH)
    first_branch_vars[name] = res
    if res:
        print(f"{name:<28} {res['var_name']:<18} {res['fractional_value']:<15.4f} {res['direction']}")
    else:
        print(f"{name:<28} No branching occurred (model may be trivially solvable)")

Set parameter WLSAccessID
Set parameter WLSSecret
Set parameter LicenseID to value 2813257
Academic license 2813257 - for non-commercial use only - registered to ki___@student.uq.edu.au
Read MPS format model from file C:\Users\KISHAN\Downloads\2club200v15p5scn.mps\2club200v15p5scn.mps
Reading time = 0.02 seconds
2club200v15p5scn: 17013 rows, 200 columns, 104811 nonzeros
Brancher: VarBranch = 1

Model                        1st Branch Var     Frac. Value     Direction
--------------------------------------------------------------------------------


AttributeError: 'CallbackConstClass' object has no attribute 'BRANCHING'

Exception ignored in: 'gurobipy._core.callbackstub'
Traceback (most recent call last):
  File "src/gurobipy/callback.pxi", line 127, in gurobipy._core.CallbackClass.callback
  File "C:\Users\KISHAN\AppData\Local\Temp\ipykernel_13060\4226416141.py", line 46, in callback
AttributeError: 'CallbackConstClass' object has no attribute 'BRANCHING'


AttributeError: 'CallbackConstClass' object has no attribute 'BRANCHING'

Exception ignored in: 'gurobipy._core.callbackstub'
Traceback (most recent call last):
  File "src/gurobipy/callback.pxi", line 127, in gurobipy._core.CallbackClass.callback
  File "C:\Users\KISHAN\AppData\Local\Temp\ipykernel_13060\4226416141.py", line 46, in callback
AttributeError: 'CallbackConstClass' object has no attribute 'BRANCHING'


...

Exception ignored in: 'gurobipy._core.callbackstub'
Traceback (most recent call last):
  File "src/gurobipy/callback.pxi", line 127, in gurobipy._core.CallbackClass.callback
  File "C:\Users\KISHAN\AppData\Local\Temp\ipykernel_13060\4226416141.py", line 46, in callback
AttributeError: 'CallbackConstClass' object has no attribute 'BRANCHING'


AttributeError: 'CallbackConstClass' object has no attribute 'BRANCHING'

Exception ignored in: 'gurobipy._core.callbackstub'
Traceback (most recent call last):
  File "src/gurobipy/callback.pxi", line 127, in gurobipy._core.CallbackClass.callback
  File "C:\Users\KISHAN\AppData\Local\Temp\ipykernel_13060\4226416141.py", line 46, in callback
AttributeError: 'CallbackConstClass' object has no attribute 'BRANCHING'


AttributeError: 'CallbackConstClass' object has no attribute 'BRANCHING'

Exception ignored in: 'gurobipy._core.callbackstub'
Traceback (most recent call last):
  File "src/gurobipy/callback.pxi", line 127, in gurobipy._core.CallbackClass.callback
  File "C:\Users\KISHAN\AppData\Local\Temp\ipykernel_13060\4226416141.py", line 46, in callback
AttributeError: 'CallbackConstClass' object has no attribute 'BRANCHING'


In [ ]:
# ═══════════════════════════════════════════════════════════════════════
# IMPORTS
# ═══════════════════════════════════════════════════════════════════════
import numpy as np
import torch
import torch.nn as nn
import torch.optim as optim
import matplotlib.pyplot as plt
from IPython.display import display
import pandas as pd
import os
import time
import datetime

# ═══════════════════════════════════════════════════════════════════════
# 1. NETWORKS
# ═══════════════════════════════════════════════════════════════════════

class CriticNet(nn.Module):
    def __init__(self, n_state, n_actions, hidden_dim=128):
        super().__init__()
        self.net = nn.Sequential(
            nn.Linear(n_state, hidden_dim),
            nn.ReLU(),
            nn.Linear(hidden_dim, hidden_dim),
            nn.ReLU(),
            nn.Linear(hidden_dim, n_actions)
        )

    def forward(self, state):
        return self.net(state)


class ActorNet(nn.Module):
    def __init__(self, n_state, n_actions, hidden_dim=128):
        super().__init__()
        self.net = nn.Sequential(
            nn.Linear(n_state, hidden_dim),
            nn.ReLU(),
            nn.Linear(hidden_dim, hidden_dim),
            nn.ReLU(),
            nn.Linear(hidden_dim, n_actions)
        )

    def forward(self, state):
        return self.net(state)


# ═══════════════════════════════════════════════════════════════════════
# 2. HELPER FUNCTIONS
# ═══════════════════════════════════════════════════════════════════════

def mask_invalid(logits, valid_actions, n_actions):
    valid_tensor = torch.tensor(valid_actions, dtype=torch.long, device=logits.device)
    mask         = torch.full((n_actions,), float('-inf'), device=logits.device)
    mask[valid_tensor] = logits[valid_tensor]
    return mask


def get_policy(actor, state_t, valid_actions, n_actions):
    logits = actor(state_t)
    masked = mask_invalid(logits, valid_actions, n_actions)
    return torch.softmax(masked, dim=0)


def sample_action_nn(actor, state_t, valid_actions, n_actions):
    with torch.no_grad():
        probs = get_policy(actor, state_t, valid_actions, n_actions)
    return int(torch.multinomial(probs, 1).item())


def greedy_action_nn(actor, state_t, valid_actions, n_actions):
    with torch.no_grad():
        probs = get_policy(actor, state_t, valid_actions, n_actions)
    return int(torch.argmax(probs).item())


def polyak_update_nn(critic, critic_target, tau=0.005):
    with torch.no_grad():
        for p, p_tgt in zip(critic.parameters(), critic_target.parameters()):
            p_tgt.data.copy_((1 - tau) * p_tgt.data + tau * p.data)


def check_terminal(state):
    """Wrapper — extracts terminal flag from is_terminal()."""
    return is_terminal(state)[0]   # <<< CHANGE >>> adjust index if needed


# ═══════════════════════════════════════════════════════════════════════
# 3. IMITATION LEARNING
# ═══════════════════════════════════════════════════════════════════════

def collect_expert_demonstrations(env, expert_policy, n_demos=100):
    """
    Collects (state, action) pairs from expert policy.
    expert_policy: function(state, valid_actions) -> action
    """
    demonstrations = []

    for demo in range(n_demos):
        state, _     = env.reset()
        episode_demo = []

        while not check_terminal(state):
            valid  = env.compute_feasible_actions(state)
            action = expert_policy(state, valid)   # <<< CHANGE >>> your expert here

            next_state, reward, terminated, truncated, _ = env.step(action)
            next_state = np.array(next_state, dtype=np.float32)

            episode_demo.append((state, action))
            state = next_state

            if terminated or truncated:
                break

        demonstrations.extend(episode_demo)
        print(f"Demo {demo+1}/{n_demos} | Steps: {len(episode_demo)}")

    print(f"Total (state, action) pairs collected: {len(demonstrations)}")
    return demonstrations


def behavioural_cloning(actor, demonstrations, n_actions,
                         n_epochs=100, lr=1e-3, batch_size=32, device=None):
    """Pre-trains actor to mimic expert via supervised learning."""
    if device is None:
        device = 'cuda' if torch.cuda.is_available() else 'cpu'
    device = torch.device(device)

    actor.to(device)
    actor.train()

    optimiser = torch.optim.Adam(actor.parameters(), lr=lr)
    loss_fn   = torch.nn.CrossEntropyLoss()

    states  = torch.FloatTensor(np.array([s for s, a in demonstrations])).to(device)
    actions = torch.LongTensor(np.array([a for s, a in demonstrations])).to(device)
    n_demos = len(demonstrations)
    losses  = []

    for epoch in range(n_epochs):
        perm    = torch.randperm(n_demos)
        states  = states[perm]
        actions = actions[perm]

        epoch_loss = 0.0
        n_batches  = 0

        for i in range(0, n_demos, batch_size):
            state_batch  = states[i:i+batch_size]
            action_batch = actions[i:i+batch_size]
            logits       = actor(state_batch)
            loss         = loss_fn(logits, action_batch)

            optimiser.zero_grad()
            loss.backward()
            optimiser.step()

            epoch_loss += loss.item()
            n_batches  += 1

        avg_loss = epoch_loss / n_batches
        losses.append(avg_loss)

        if (epoch + 1) % 10 == 0:
            print(f"BC Epoch {epoch+1}/{n_epochs} | Loss: {avg_loss:.4f}")

    print("Behavioural cloning complete.")
    return losses


def pretrain_critic(critic, demonstrations, env,
                    gamma=0.99, n_epochs=50, lr=1e-3, device=None):
    """Pre-trains critic using Monte Carlo returns from expert demos."""
    if device is None:
        device = 'cuda' if torch.cuda.is_available() else 'cpu'
    device = torch.device(device)

    critic.to(device)
    critic.train()

    optimiser = torch.optim.Adam(critic.parameters(), lr=lr)
    n_actions = env.action_space.n

    states  = []
    actions = []
    returns = []
    cumulative = 0.0

    for state, action in reversed(demonstrations):
        cumulative = cumulative * gamma
        states.insert(0, state)
        actions.insert(0, action)
        returns.insert(0, cumulative)

    states_t  = torch.FloatTensor(np.array(states)).to(device)
    actions_t = torch.LongTensor(np.array(actions)).to(device)
    returns_t = torch.FloatTensor(np.array(returns)).to(device)

    for epoch in range(n_epochs):
        q_vals = critic(states_t)
        q_sa   = q_vals.gather(1, actions_t.unsqueeze(1)).squeeze(1)
        loss   = ((returns_t - q_sa) ** 2).mean()

        optimiser.zero_grad()
        loss.backward()
        optimiser.step()

        if (epoch + 1) % 10 == 0:
            print(f"Critic Pretrain Epoch {epoch+1}/{n_epochs} | Loss: {loss.item():.4f}")

    print("Critic pretraining complete.")


# ═══════════════════════════════════════════════════════════════════════
# 4. MAIN ACTOR-CRITIC LOOP
# ═══════════════════════════════════════════════════════════════════════

def actor_critic_nn(
    env,
    gamma: float               = 0.99,
    alpha_w: float             = 1e-3,
    alpha_theta: float         = 1e-5,
    tau: float                 = 0.005,
    hidden_dim: int            = 128,
    n_episodes: int            = 1000,      # <<< CHANGE >>>
    max_steps: int             = 500,       # <<< CHANGE >>>
    device: str                = None,
    entropy_coeff_start: float = 0.1,
    entropy_coeff_end: float   = 0.001,
    verbose: bool              = False,
    pretrained_actor           = None,
    pretrained_critic          = None,
):
    if device is None:
        device = 'cuda' if torch.cuda.is_available() else 'cpu'
    print(f"Using device: {device}")
    device = torch.device(device)

    n_state   = env.observation_space.shape[0]
    n_actions = env.action_space.n

    # ── Networks ────────────────────────────────────────────────────────
    if pretrained_actor is not None:
        actor = pretrained_actor.to(device)
        print("Using pretrained actor.")
    else:
        actor = ActorNet(n_state, n_actions, hidden_dim).to(device)

    if pretrained_critic is not None:
        critic        = pretrained_critic.to(device)
        critic_target = CriticNet(n_state, n_actions, hidden_dim).to(device)
        critic_target.load_state_dict(critic.state_dict())
        print("Using pretrained critic.")
    else:
        critic        = CriticNet(n_state, n_actions, hidden_dim).to(device)
        critic_target = CriticNet(n_state, n_actions, hidden_dim).to(device)
        critic_target.load_state_dict(critic.state_dict())

    for p in critic_target.parameters():
        p.requires_grad = False

    critic_opt = optim.Adam(critic.parameters(), lr=alpha_w)
    actor_opt  = optim.Adam(actor.parameters(),  lr=alpha_theta)

    episode_returns = []

    for episode in range(n_episodes):
        fraction      = episode / max(1, n_episodes - 1)
        entropy_coeff = entropy_coeff_start + fraction * (entropy_coeff_end - entropy_coeff_start)

        state, _     = env.reset()
        I            = 1.0
        total_return = 0.0
        trajectory   = []

        for step in range(max_steps):
            if check_terminal(state):
                break

            state_t = torch.FloatTensor(state).to(device)
            valid   = env.compute_feasible_actions(state)
            action  = sample_action_nn(actor, state_t, valid, n_actions)

            next_state, reward, terminated, truncated, _ = env.step(action)

            assert next_state is not None, \
                f"env.step() returned None at episode {episode}, action {action}"

            done         = terminated or truncated
            total_return += reward

            if verbose:
                N           = len(state) // 2
                first_half  = "  ".join(f"{int(v)}" for v in state[:N])
                second_half = "  ".join(f"{int(v)}" for v in state[N:])
                action_str  = str(env.id_to_actionTuple[action])
                print(f"┌─ Episode {episode+1:4d} | Step {step+1:4d} {'─'*30}")
                print(f"│  State  (1st half) : {first_half}")
                print(f"│  State  (2nd half) : {second_half}")
                print(f"│  Action            : {action_str}")
                print(f"│  Reward            : {reward:.3f}")
                print(f"└{'─'*50}")

            next_state_t = torch.FloatTensor(next_state).to(device)

            with torch.no_grad():
                if done:
                    td_target = torch.tensor(reward, dtype=torch.float32, device=device)
                else:
                    next_valid    = env.compute_feasible_actions(next_state)
                    next_q_vals   = critic_target(next_state_t)
                    next_q_masked = mask_invalid(next_q_vals, next_valid, n_actions)
                    best_q_next   = next_q_masked.max()
                    td_target     = torch.tensor(
                                        reward + gamma * best_q_next.item(),
                                        dtype=torch.float32, device=device
                                    )

            q_vals      = critic(state_t)
            q_sa        = q_vals[action]
            critic_loss = (td_target - q_sa) ** 2
            critic_opt.zero_grad()
            critic_loss.backward()
            critic_opt.step()

            logits   = actor(state_t)
            masked   = mask_invalid(logits, valid, n_actions)
            probs    = torch.softmax(masked, dim=0)
            log_prob = torch.log_softmax(masked, dim=0)[action]
            entropy  = -torch.sum(probs * torch.log(probs + 1e-10))

            with torch.no_grad():
                q_sa_baseline = critic(state_t)[action]

            actor_loss = -I * log_prob * q_sa_baseline - entropy_coeff * entropy
            actor_opt.zero_grad()
            actor_loss.backward()
            actor_opt.step()

            I     *= gamma
            state  = next_state
            trajectory.append((state, action, reward))

            if done:
                break

        trajectory.append((state, None, 0.0))
        polyak_update_nn(critic, critic_target, tau)
        episode_returns.append(total_return)

        log_every = max(1, n_episodes // 10)
        if (episode + 1) % log_every == 0:
            avg = np.mean(episode_returns[-log_every:])
            print(f"Episode {episode+1:5d} | Avg return: {avg:.2f} | Entropy coeff: {entropy_coeff:.4f}")

    return actor, critic, episode_returns


# ═══════════════════════════════════════════════════════════════════════
# 5. POLICY EXECUTION
# ═══════════════════════════════════════════════════════════════════════

def run_policy_nn(env, actor, time_limit_hours=1, device=None):
    if device is None:
        device = 'cuda' if torch.cuda.is_available() else 'cpu'
    device    = torch.device(device)
    n_actions = env.action_space.n

    state, _           = env.reset()
    total_return       = 0.0
    trajectory         = []
    time_limit_seconds = time_limit_hours * 3600
    start_time         = time.perf_counter()

    while not check_terminal(state):
        elapsed = time.perf_counter() - start_time
        if elapsed >= time_limit_seconds:
            print(f"Time limit of {time_limit_hours}h reached after {len(trajectory)} steps.")
            break

        state_t = torch.FloatTensor(state).to(device)
        valid   = env.compute_feasible_actions(state)
        action  = greedy_action_nn(actor, state_t, valid, n_actions)

        next_state, reward, terminated, truncated, _ = env.step(action)

        assert next_state is not None, \
            f"env.step() returned None, action={action}"

        next_state    = np.array(next_state, dtype=np.float32)
        total_return += reward
        trajectory.append((state, action, reward))
        state = next_state

        if terminated or truncated:
            break

    trajectory.append((state, None, 0.0))

    elapsed = time.perf_counter() - start_time
    print(f"Policy execution time: {elapsed/3600:.4f}h | Steps: {len(trajectory)-1} | Total return: {total_return:.3f}")

    return trajectory, total_return


# ═══════════════════════════════════════════════════════════════════════
# 6. DISPLAY FUNCTIONS
# ═══════════════════════════════════════════════════════════════════════

def format_state(state):
    N           = len(state) // 2
    first_half  = state[:N]
    second_half = state[N:]
    line1 = "  ".join(f"{int(v)}" for v in first_half)
    line2 = "  ".join(f"{int(v)}" for v in second_half)
    return f"{line1}\n{line2}"


def print_trajectory(trajectory, env):
    returns_to_go = []
    cumulative    = 0.0
    for _, _, reward in reversed(trajectory):
        cumulative += reward
        returns_to_go.insert(0, cumulative)

    rows = []
    for i, (state, action, reward) in enumerate(trajectory):
        action_str = str(env.id_to_actionTuple[action]) if action is not None else "TERMINAL"
        rows.append({
            "Step"             : i + 1,
            "State"            : format_state(state),
            "Action"           : action_str,
            "Return from here" : f"{returns_to_go[i]:.3f}",
        })

    df = pd.DataFrame(rows).set_index("Step")
    pd.set_option("display.max_colwidth", None)
    styled = (
        df.style
        .set_properties(**{
            "white-space" : "pre",
            "text-align"  : "left",
            "font-family" : "monospace",
            "font-size"   : "13px",
            "padding"     : "6px 12px",
        })
        .set_table_styles([{
            "selector": "th",
            "props": [
                ("background-color", "#4A90D9"),
                ("color", "white"),
                ("font-size", "13px"),
                ("padding", "6px 12px"),
            ]
        }])
    )
    display(styled)


def print_learning_summary(actor, env, episode_returns, device=None):
    if device is None:
        device = 'cuda' if torch.cuda.is_available() else 'cpu'
    device    = torch.device(device)
    n_actions = env.action_space.n

    state, _     = env.reset()
    trajectory   = []
    total_return = 0.0

    while not check_terminal(state):
        state_t = torch.FloatTensor(state).to(device)
        valid   = env.compute_feasible_actions(state)
        action  = greedy_action_nn(actor, state_t, valid, n_actions)

        next_state, reward, terminated, truncated, _ = env.step(action)

        assert next_state is not None
        next_state    = np.array(next_state, dtype=np.float32)
        total_return += reward
        trajectory.append((state, action, reward))
        state = next_state

        if terminated or truncated:
            break

    trajectory.append((state, None, 0.0))

    returns_to_go = []
    cumulative    = 0.0
    for _, _, reward in reversed(trajectory):
        cumulative += reward
        returns_to_go.insert(0, cumulative)

    rows = []
    for i, (state, action, reward) in enumerate(trajectory):
        action_str = str(env.id_to_actionTuple[action]) if action is not None else "TERMINAL"
        rows.append({
            "Step"             : i + 1,
            "State"            : format_state(state),
            "Optimal Action"   : action_str,
            "Return from here" : f"{returns_to_go[i]:.3f}",
        })

    df = pd.DataFrame(rows).set_index("Step")
    pd.set_option("display.max_colwidth", None)
    styled = (
        df.style
        .set_properties(**{
            "white-space" : "pre",
            "text-align"  : "left",
            "font-family" : "monospace",
            "font-size"   : "13px",
            "padding"     : "6px 12px",
        })
        .set_table_styles([{
            "selector": "th",
            "props": [
                ("background-color", "#2E8B57"),
                ("color", "white"),
                ("font-size", "13px"),
                ("padding", "6px 12px"),
            ]
        }])
    )

    print(f"\n{'='*60}")
    print(f"LEARNING SUMMARY")
    print(f"{'='*60}")
    print(f"Total episodes trained : {len(episode_returns)}")
    print(f"Average return (all)   : {np.mean(episode_returns):.3f}")
    print(f"Best episode return    : {np.max(episode_returns):.3f}")
    print(f"Final policy return    : {total_return:.3f}")
    print(f"Trajectory length      : {len(trajectory)-1} steps")
    print(f"{'='*60}\n")
    display(styled)


def plot_policy_at_step_nn(actor, trajectory, step, env, device=None):
    if device is None:
        device = 'cuda' if torch.cuda.is_available() else 'cpu'
    device    = torch.device(device)
    n_actions = env.action_space.n

    state, action, _ = trajectory[step]
    state_t  = torch.FloatTensor(state).to(device)
    valid    = env.compute_feasible_actions(state)

    with torch.no_grad():
        probs = get_policy(actor, state_t, valid, n_actions).cpu().numpy()

    entropy = -np.sum(probs[valid] * np.log(probs[valid] + 1e-10))
    labels  = [str(env.id_to_actionTuple[a]) for a in valid]
    values  = probs[valid]

    fig, ax = plt.subplots(figsize=(8, 4))
    bars    = ax.bar(range(len(valid)), values, tick_label=labels)

    if action is not None:
        taken_idx = list(valid).index(action)
        bars[taken_idx].set_color("orange")

    ax.set_xlabel("Action")
    ax.set_ylabel("Probability")
    ax.set_title(f"Step {step+1} | Action: {env.id_to_actionTuple[action]} | Entropy={entropy:.3f}")
    plt.xticks(rotation=45, ha='right')
    plt.tight_layout()
    display(fig)
    plt.close(fig)


def plot_rewards(episode_returns, window=None):
    episodes = np.arange(1, len(episode_returns) + 1)
    returns  = np.array(episode_returns)

    if window is None:
        window = len(episode_returns)
    else:
        window = min(window, len(episode_returns))

    rolling_avg = np.convolve(returns, np.ones(window) / window, mode='valid')
    rolling_eps = np.arange(window, len(episode_returns) + 1)

    fig, ax = plt.subplots(figsize=(10, 5))
    ax.plot(episodes, returns, color='steelblue', alpha=0.3,
            linewidth=0.8, label='Episode return')
    ax.plot(rolling_eps, rolling_avg, color='orange',
            linewidth=2, label=f'Rolling avg (window={window})')
    ax.set_xlabel("Episode")
    ax.set_ylabel("Total Return")
    ax.set_title("Rewards vs Episodes")
    ax.legend()
    ax.grid(True, alpha=0.3)
    plt.tight_layout()
    display(fig)
    plt.close(fig)


def plot_averaged_returns(all_returns, N_runs):
    all_returns  = np.array(all_returns)
    mean_returns = np.mean(all_returns, axis=0)
    std_returns  = np.std(all_returns,  axis=0)
    episodes     = np.arange(1, all_returns.shape[1] + 1)

    fig, ax = plt.subplots(figsize=(10, 5))
    ax.plot(episodes, mean_returns, color='steelblue',
            linewidth=2, label=f'Mean return ({N_runs} runs)')
    ax.fill_between(episodes,
                    mean_returns - std_returns,
                    mean_returns + std_returns,
                    color='steelblue', alpha=0.2,
                    label='± 1 std dev')
    ax.set_xlabel("Episode")
    ax.set_ylabel("Total Return")
    ax.set_title(f"Average Return across {N_runs} Runs")
    ax.legend()
    ax.grid(True, alpha=0.3)
    plt.tight_layout()
    display(fig)
    plt.close(fig)


# ═══════════════════════════════════════════════════════════════════════
# 7. ENTRY POINT
# ═══════════════════════════════════════════════════════════════════════

if __name__ == "__main__":

    env = MyMDPEnv()   # <<< CHANGE >>>

    n_state   = env.observation_space.shape[0]
    n_actions = env.action_space.n
    hidden_dim = 128   # <<< CHANGE >>>

    # ── Option A: Train from scratch ──────────────────────────────────
    actor, critic, episode_returns = actor_critic_nn(
        env                 = env,
        gamma               = 0.99,
        alpha_w             = 1e-3,
        alpha_theta         = 1e-5,
        tau                 = 0.005,
        hidden_dim          = hidden_dim,
        n_episodes          = 1000,        # <<< CHANGE >>>
        max_steps           = 500,         # <<< CHANGE >>>
        entropy_coeff_start = 0.1,
        entropy_coeff_end   = 0.001,
        verbose             = False,
    )

    # ── Option B: Train with imitation learning first ─────────────────
    # def my_expert_policy(state, valid_actions):
    #     # <<< CHANGE >>> your expert here e.g. Gurobi
    #     return valid_actions[0]
    #
    # demonstrations = collect_expert_demonstrations(env, my_expert_policy, n_demos=100)
    #
    # actor  = ActorNet(n_state, n_actions, hidden_dim)
    # critic = CriticNet(n_state, n_actions, hidden_dim)
    #
    # behavioural_cloning(actor, demonstrations, n_actions, n_epochs=100)
    # pretrain_critic(critic, demonstrations, env, n_epochs=50)
    #
    # actor, critic, episode_returns = actor_critic_nn(
    #     env               = env,
    #     pretrained_actor  = actor,
    #     pretrained_critic = critic,
    #     n_episodes        = 1000,   # <<< CHANGE >>>
    #     max_steps         = 500,    # <<< CHANGE >>>
    # )

    # ── Save actor ────────────────────────────────────────────────────
    torch.save(actor.state_dict(), "actor.pth")   # <<< CHANGE >>> path
    print("Actor saved.")

    # ── Plots and results ─────────────────────────────────────────────
    plot_rewards(episode_returns)
    print_learning_summary(actor, env, episode_returns)

    # ── Run learnt policy ─────────────────────────────────────────────
    trajectory, total_return = run_policy_nn(env, actor, time_limit_hours=1)
    print_trajectory(trajectory, env)
    plot_policy_at_step_nn(actor, trajectory, step=0, env=env)

    # ── Multiple runs ─────────────────────────────────────────────────
    # N_runs      = 5   # <<< CHANGE >>>
    # all_returns = []
    # for run in range(N_runs):
    #     print(f"\nRUN {run+1}/{N_runs}")
    #     _, _, episode_returns = actor_critic_nn(env=env, n_episodes=1000)
    #     all_returns.append(episode_returns)
    # plot_averaged_returns(all_returns, N_runs)

    # ── Load saved actor ──────────────────────────────────────────────
    # actor = ActorNet(n_state, n_actions, hidden_dim)
    # actor.load_state_dict(torch.load("actor.pth", map_location='cpu'))
    # actor.eval()
    # trajectory, total_return = run_policy_nn(env, actor, time_limit_hours=1)